In [ ]:
#import shapely 
#import open3d as o3d
#import laspy
import numpy as np
#from pathfinding3d.core.diagonal_movement import DiagonalMovement
#from pathfinding3d.core.grid import Grid
#from pathfinding3d.finder.a_star import AStarFinder
import trimesh as tm

In [ ]:
import skeletor as sk
import trimesh as tm
import pyproj
import numpy as np

mesh = tm.load_mesh('/Users/hugh/Desktop/SUNFISH_PATHFINDING_WORK/emerald_final/multibeam_slam_surface_mesh.ply')

#to coords
T_4x4 = np.array([
    [0,  1,  0,  0],
    [1,  0,  0,  0],
    [0,  0, -1,  0],
    [0,  0,  0,  1]
])

mesh.apply_transform(T_4x4)

print(mesh.is_watertight)

fixed = sk.pre.fix_mesh(mesh, remove_disconnected=5, inplace=False)

skel = sk.skeletonize.by_mean_curvature(fixed  , SL=3)

sk.post.remove_bristles(skel , mesh , inplace=True)


True


Collapsing edges: 100%|█████████▉| 147358/147362 [00:03<00:00, 48613.70it/s]


<Skeleton(vertices=(582, 3), edges=(581, 2), method=mean_curvature)>

In [82]:
skel_smoth = sk.post.smooth(s=skel , window=2)

In [88]:
skel_smoth.show(mesh=True)

In [ ]:

from shapely.geometry import MultiLineString , LineString
from shapely.ops import linemerge


segments = [
    LineString([skel_smoth.vertices[start], skel_smoth.vertices[end]])
    for start, end in skel_smoth.edges
]


multi_line = MultiLineString(segments)

#make whole skele
merged_skeleton = linemerge(multi_line)

In [ ]:
import networkx as nx
from shapely.geometry import LineString, MultiLineString
from shapely.ops import linemerge

#do you want only the largest component?
G = nx.Graph()
G.add_edges_from(skel_smoth.edges)


largest_nodes = max(nx.connected_components(G), key=len)
largest_subgraph = G.subgraph(largest_nodes)


segments = [
    LineString([skel_smoth.vertices[u], skel_smoth.vertices[v]])
    for u, v in largest_subgraph.edges()
]


largest_component_geometry = linemerge(MultiLineString(segments))

In [91]:
import geopandas as gp 
import pyproj

df = gp.GeoDataFrame(data=[{"skele" : merged_skeleton}] , geometry="skele")

with open("/Users/hugh/Desktop/SUNFISH_PATHFINDING_WORK/emerald_final/map_crs.txt" , "r") as f:
    df = df.set_crs(pyproj.CRS.from_wkt(f.read()))

    df = df.to_crs(5070)

In [93]:
df.to_file("emerald.fgb")

In [55]:
#turner
merged_skeleton.length

2753.0986347385283

In [ ]:
#clear cut
merged_skeleton.length

1761.9292859024333

In [95]:
#emerald
merged_skeleton.length

1483.3148646972527